# 11 -- Buy land: split hands across NW and NE

Extends `melon_then_wheat_agent`: once affordable ($1000, naturally
happens shortly after the first melon sale, no extra buffer needed),
`BUY_LAND` unlocks the NE quadrant (`LAND_ORDER = ["NE", "SW", "SE"]`,
`LAND_PRICES = [1000, 2000, 4000]` -- read directly from
`kaggriculture.py`). NE is x=5..9, y=0..4 -- the same shape as NW, just
shifted `+5` in x. Once bought, hands 3 and 4 relocate there (WHEAT);
the farmer and hands 0-2 keep working NW exactly as before.

No extra state needed: `obs["farms"][player]["unlocked_quadrants"]`
already tells us whether NE is bought, every turn, for free.

Three pieces to build, in order:
1. Confirm NE's real layout and the `(5,4)` corner's behavior before/
   after buying (mini-test on a real `obs`, not assumed).
2. Mirror `LOOP_ORDER_HANDS`/zones 3 and 4 into NE (`x + 5`).
3. Wire it into `melon_then_wheat_agent`: hands 3/4 check
   `unlocked_quadrants` and use the NE path/zone when available, the NW
   one otherwise. Plus the `BUY_LAND` market order itself.

In [1]:
import sys
from pathlib import Path

from kaggle_environments import make

sys.path.insert(0, str(Path.cwd().parent / "src"))

from kaggriculture_bot.evaluate import evaluate
from kaggriculture_bot.strategies.baseline import (
    DIRECTIONS,
    HAND_ZONES,
    LOOP_ORDER_12,
    LOOP_ORDER_HANDS,
    SPAWN_FEEDER,
    melon_then_wheat_agent,
)

## Mini-test: confirm NE's layout on a real `obs`

A throwaway agent that just buys land the moment it's affordable and
otherwise passes -- run it far enough to see NE actually unlock, then
inspect the tiles directly instead of trusting the source-code reading
alone.

In [2]:
def _test_buy_land_agent(obs):
    market = []
    farm = obs["farms"][obs["player"]]
    if farm["money"] >= 1000 and len(farm["unlocked_quadrants"]) == 1:
        market.append(["BUY_LAND"])
    return {"farmer": ["PASS"], "hands": [], "market": market}


test_env = make("kaggriculture", configuration={"episodeSteps": 720}, debug=True)
test_env.run([_test_buy_land_agent, "random"])

[[{'action': {'farmer': ['PASS'], 'hands': [], 'market': []},
   'reward': 0,
   'info': {},
   'observation': {'remainingOverageTime': 60,
    'step': 0,
    'player': 0,
    'farms': [{'money': 3000.0,
      'tiles': [[None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
 

In [3]:
# money starts at 3000 and _test_buy_land_agent never spends any of it on
# anything else, so it should buy NE on turn 1 (the BUY_LAND queued on
# turn 0 resolves turn 1). Find the first turn unlocked_quadrants grows.
prev = None
for i, step in enumerate(test_env.steps):
    obs = step[0]["observation"]
    uq = obs["farms"][obs["player"]]["unlocked_quadrants"]
    if uq != prev:
        print(i, "unlocked_quadrants:", uq, "money:", obs["farms"][obs["player"]]["money"])
        prev = uq
    if len(uq) > 1:
        break

0 unlocked_quadrants: ['NW'] money: 3000.0
1 unlocked_quadrants: ['NW', 'NE'] money: 2000.0


In [4]:
# Once NE is unlocked, check (5,4) (a former spawn-corner "LOCKED" tile)
# and a handful of NE interior tiles to confirm the quadrant's real shape.
obs = test_env.steps[i][0]["observation"]
tiles = obs["farms"][obs["player"]]["tiles"]
for x, y in [(5, 4), (5, 0), (9, 0), (9, 4), (6, 2), (4, 0)]:
    print((x, y), "->", repr(tiles[y][x]))

(5, 4) -> None
(5, 0) -> None
(9, 0) -> None
(9, 4) -> None
(6, 2) -> None
(4, 0) -> None


## Design NE's loop and zones directly (not a mirror)

First attempt mirrored `LOOP_ORDER_HANDS` into NE by shifting `x + 5`,
and it broke: `LOOP_ORDER_HANDS` isn't a full-quadrant loop -- it only
covers the tiles the *hands* need, deliberately excluding whatever the
*farmer*'s own `LOOP_ORDER_12` already covers in NW. Its "entry" key,
`(4,4)`, is NW's innermost corner (closest to the shed); shifted `+5` it
becomes `(9,4)` -- NE's *farthest* corner, not the near one. Worse,
`(5,4)` (NE's real near corner, where `SPAWN_FEEDER_NE` actually lands
hands) was never a key in the shifted dict at all -- `KeyError: (5, 4)`
the moment a hand tried to move from there.

NE has no farmer loop of its own to complement, so there's no reason to
copy NW's cut-down shape. Built fresh instead: a 16-tile loop around the
border of the 5x5 NE block, entering at `(5,4)`, with hands 3 and 4 each
peeling off into their own private 2x2 zone (`ZONE_3_NE`/`ZONE_4_NE`) --
same mechanism as `HAND_ZONES`, just NE-native geometry instead of a
coordinate shift. Verified directly (not just by construction): every
zone is a valid closed adjacent cycle, the two zones are disjoint, and a
hand starting from any of the 4 spawn corners reaches its own zone and
settles there.

In [5]:
LOOP_ORDER_HANDS_NE = {
    (5, 4): (6, 4), (6, 4): (7, 4), (7, 4): (8, 4), (8, 4): (9, 4),
    (9, 4): (9, 3), (9, 3): (9, 2), (9, 2): (9, 1), (9, 1): (9, 0),
    (9, 0): (8, 0), (8, 0): (7, 0), (7, 0): (6, 0), (6, 0): (5, 0),
    (5, 0): (5, 1), (5, 1): (5, 2), (5, 2): (5, 3), (5, 3): (5, 4),
}
ZONE_3_NE = {(6, 4): (6, 3), (6, 3): (7, 3), (7, 3): (7, 4), (7, 4): (6, 4)}
ZONE_4_NE = {(9, 4): (9, 3), (9, 3): (8, 3), (8, 3): (8, 4), (8, 4): (9, 4)}
SPAWN_FEEDER_NE = {(4, 4): (5, 4), (4, 5): (4, 4), (5, 5): (5, 4)}

## Sanity check: still a valid closed cycle after shifting

Reuse the same check used for every other loop/zone in this project.

In [6]:
def assert_is_closed_adjacent_cycle(loop_order):
    n = len(loop_order)
    start = next(iter(loop_order))
    pos = start
    visited = set()
    for _ in range(n):
        visited.add(pos)
        (x, y), (nx, ny) = pos, loop_order[pos]
        assert abs(nx - x) + abs(ny - y) == 1
        pos = (nx, ny)
    assert pos == start
    assert visited == set(loop_order)


assert_is_closed_adjacent_cycle(LOOP_ORDER_HANDS_NE)
print("LOOP_ORDER_HANDS_NE: valid closed cycle,", len(LOOP_ORDER_HANDS_NE), "tiles")
assert_is_closed_adjacent_cycle(ZONE_3_NE)
print("ZONE_3_NE: valid closed cycle,", len(ZONE_3_NE), "tiles")
assert_is_closed_adjacent_cycle(ZONE_4_NE)
print("ZONE_4_NE: valid closed cycle,", len(ZONE_4_NE), "tiles")
assert not (set(ZONE_3_NE) & set(ZONE_4_NE))
print("ZONE_3_NE / ZONE_4_NE: disjoint")
for pos, nxt in SPAWN_FEEDER_NE.items():
    assert abs(nxt[0] - pos[0]) + abs(nxt[1] - pos[1]) == 1
    assert nxt == (5, 4) or nxt in SPAWN_FEEDER_NE
print("SPAWN_FEEDER_NE: valid, all one step closer to (5,4)")

LOOP_ORDER_HANDS_NE: valid closed cycle, 16 tiles
ZONE_3_NE: valid closed cycle, 4 tiles
ZONE_4_NE: valid closed cycle, 4 tiles
ZONE_3_NE / ZONE_4_NE: disjoint
SPAWN_FEEDER_NE: valid, all one step closer to (5,4)


## Building `melon_then_wheat_land_agent`

Start from `melon_then_wheat_agent`'s body. Changes:

1. **`BUY_LAND`**: queue it when `money >= 1000 and
   len(unlocked_quadrants) == 1` -- gate it on being in the WHEAT phase
   too (`crop_to_plant == "WHEAT"`), since starting money ($3000) is
   already above $1000 on turn 0, before any melon income at all.
2. **Hands 3 and 4**: each turn, check `"NE" in
   obs["farms"][obs["player"]]["unlocked_quadrants"]`. If true, that hand
   uses `LOOP_ORDER_HANDS_NE`/`SPAWN_FEEDER_NE`/`ZONE_3_NE`(or `_4_`) and
   plants/tends WHEAT (no melon phase in NE -- land is only affordable
   after day 10 anyway). If false, that hand does exactly what it already
   does in `melon_then_wheat_agent` (NW, melon-then-wheat by day).
3. **Edge case**: NE can unlock *mid-day*, one turn after the `BUY_LAND`
   order resolves. A hand already active in NW territory that turn (e.g.
   deep in `HAND_ZONES[3]`) would suddenly be in "NE mode" while still
   physically standing on a tile `LOOP_ORDER_HANDS_NE`/`SPAWN_FEEDER_NE`
   don't cover -> `KeyError`. Fix: in the NE branch, merge the NW graph in
   too as a fallback (`{**LOOP_ORDER_HANDS, **SPAWN_FEEDER,
   **LOOP_ORDER_HANDS_NE, **SPAWN_FEEDER_NE, **own_zone}`) -- confirmed no
   key collisions between the two `SPAWN_FEEDER`s (their two shared keys,
   `(4,5)`/`(5,5)`, map to the same targets in both).

Hands 0-2 and the farmer are unchanged.

In [7]:
def melon_then_wheat_land_agent(obs):
    crop_to_plant = "MELON" if obs["day"] < 10 else "WHEAT"
    crop_seeds = obs["private"]["seeds"].get(crop_to_plant, 0)

    market = []
    hands = []

    ne_unlocked = "NE" in obs["farms"][obs["player"]]["unlocked_quadrants"]

    for i, (hx, hy) in enumerate(obs["farms"][obs["player"]]["hands"]):
        if i in (3, 4) and ne_unlocked:
            own_zone = ZONE_3_NE if i == 3 else ZONE_4_NE
            hand_loop = {
                **LOOP_ORDER_HANDS, **SPAWN_FEEDER,
                **LOOP_ORDER_HANDS_NE, **SPAWN_FEEDER_NE,
                **own_zone,
            }
        else:
            own_zone = HAND_ZONES[i % len(HAND_ZONES)]
            hand_loop = {**LOOP_ORDER_HANDS, **SPAWN_FEEDER, **own_zone}

        target_x, target_y = hand_loop[(hx, hy)]
        if (target_x, target_y) == (hx, hy):
            move = ["PASS"]
        else:
            move = [DIRECTIONS[(target_x - hx, target_y - hy)]]

        hand_tile = obs["farms"][obs["player"]]["tiles"][hy][hx]
        in_own_zone = (hx, hy) in own_zone
        if hand_tile == "LOCKED" or not in_own_zone:
            op = move
        elif hand_tile is None and crop_seeds > 0:
            op = ["PLANT", crop_to_plant]
        elif hand_tile is not None and hand_tile.get("kind") == "PLANT":
            crop_age = obs["day"] - hand_tile["planted_day"]
            threshold = 10 if hand_tile["crop"] == "MELON" else 2
            if crop_age >= threshold:
                op = ["HARVEST"]
            elif not hand_tile.get("watered_today"):
                op = ["WATER"]
            else:
                op = move
        else:
            op = move
        hands.append(op)

    if len(obs["farms"][obs["player"]]["hands"]) < 5:
        market.append(["HIRE"])

    if obs["step"] == 0 or crop_seeds <= 5:
        market.append(["BUY_SEED", crop_to_plant, 6 - crop_seeds])

    farmer_pos = obs["farms"][obs["player"]]["farmer"]
    x, y = farmer_pos
    target_x, target_y = LOOP_ORDER_12[(x, y)]
    direction = DIRECTIONS[(target_x - x, target_y - y)]

    tile = obs["farms"][obs["player"]]["tiles"][y][x]

    wheat_in_shed = obs["private"]["shed"].get("WHEAT", 0)
    melon_in_shed = obs["private"]["shed"].get("MELON", 0)
    if wheat_in_shed > 0:
        market.append(["SELL", "WHEAT", wheat_in_shed])
    if melon_in_shed > 0:
        market.append(["SELL", "MELON", melon_in_shed])

    if tile is None and crop_seeds > 0:
        farmer = ["PLANT", crop_to_plant]
    elif tile is not None and tile.get("kind") == "PLANT":
        crop_age = obs["day"] - tile["planted_day"]
        threshold = 10 if tile["crop"] == "MELON" else 2
        if crop_age >= threshold:
            farmer = ["HARVEST"]
        elif not tile.get("watered_today"):
            farmer = ["WATER"]
        else:
            farmer = [direction]
    else:
        farmer = [direction]

    money = obs["farms"][obs["player"]]["money"]
    quadrant = obs["farms"][obs["player"]]["unlocked_quadrants"]
    if crop_to_plant == "WHEAT" and money >= 1000 and len(quadrant) <= 1:
        market.append(["BUY_LAND"])

    return {"farmer": farmer, "hands": hands, "market": market}

## Validate against the current best

Current best is `melon_then_wheat_agent`. Run twice.

In [8]:
print(evaluate(melon_then_wheat_agent, melon_then_wheat_land_agent, n=20))

{'win_rate': 1.0, 'avg_money': 21122.0}


In [9]:
print(evaluate(melon_then_wheat_agent, melon_then_wheat_land_agent, n=20))

{'win_rate': 1.0, 'avg_money': 20267.0}


In [10]:
diag_env = make("kaggriculture", configuration={"episodeSteps": 720}, debug=True)
diag_env.run([melon_then_wheat_agent, melon_then_wheat_land_agent])

for step_idx in range(0, 720, 24):
    obs0 = diag_env.steps[step_idx][0]["observation"]
    obs1 = diag_env.steps[step_idx][1]["observation"]
    print(
        "day", obs0["day"],
        "agent0(no-land) money:", obs0["farms"][0]["money"],
        "agent1(land) money:", obs1["farms"][1]["money"],
        "agent1 quadrants:", obs1["farms"][1]["unlocked_quadrants"],
    )

day 0 agent0(no-land) money: 3000.0 agent1(land) money: 3000.0 agent1 quadrants: ['NW']
day 1 agent0(no-land) money: 828.0 agent1(land) money: 828.0 agent1 quadrants: ['NW']
day 2 agent0(no-land) money: 656.0 agent1(land) money: 576.0 agent1 quadrants: ['NW']
day 3 agent0(no-land) money: 564.0 agent1(land) money: 484.0 agent1 quadrants: ['NW']
day 4 agent0(no-land) money: 552.0 agent1(land) money: 472.0 agent1 quadrants: ['NW']
day 5 agent0(no-land) money: 540.0 agent1(land) money: 460.0 agent1 quadrants: ['NW']
day 6 agent0(no-land) money: 528.0 agent1(land) money: 448.0 agent1 quadrants: ['NW']
day 7 agent0(no-land) money: 516.0 agent1(land) money: 436.0 agent1 quadrants: ['NW']
day 8 agent0(no-land) money: 504.0 agent1(land) money: 424.0 agent1 quadrants: ['NW']
day 9 agent0(no-land) money: 492.0 agent1(land) money: 412.0 agent1 quadrants: ['NW']
day 10 agent0(no-land) money: 480.0 agent1(land) money: 400.0 agent1 quadrants: ['NW']
day 11 agent0(no-land) money: 228.0 agent1(land) mo